# **Laboratorio Clase 42: Tracking en video**

Profesor: Carlos Aspillaga

Al igual que en laboratorios anteriores, debe responder el laboratorio de forma individual y asegurarse de entregar con todas las celdas ejecutadas.
Habrá un bonus de 1 décima por orden y redacción a criterio del ayudante corrector.

In [1]:
# ==========================================
# Phase 1: Environment and Dependency Setup
# ==========================================
!pip install -U ultralytics supervision roboflow opencv-python

     ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 46.9/46.9 kB 5.0 MB/s eta 0:00:00
     ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 107.2/107.2 kB 10.9 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 1.4/1.4 MB 88.6 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 460.4/460.4 kB 47.2 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 373.9/373.9 kB 40.6 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 35.0/35.0 MB 53.6 MB/s eta 0:00:00:00:0100:01
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 5.4/5.4 MB 141.4 MB/s eta 0:00:0000:01
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 204.0/204.0 kB 23.8 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 58.4/58.4 kB 6.9 MB/s eta 0:00:00
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 97.6/97.6 kB 11.7 MB/s eta 0:00:00
  Attempting uninstall: typer
    Found existing installation: typer 0.27.3
    Uninstalling typer-0.27.3:
      Successfully uninstalled typer-0.27.3


In [2]:
import torch
import cv2
import numpy as np
import os
import urllib.request
from collections import defaultdict
from IPython.display import HTML, display
from base64 import b64encode

# Verify PyTorch CUDA Allocation for hardware-accelerated inference
print(f"CUDA Available: {torch.cuda.is_available()}")
if torch.cuda.is_available():
    print(f"Allocated Accelerator: {torch.cuda.get_device_name(0)}")

CUDA Available: True
Allocated Accelerator: Tesla T4


In [3]:
!wget https://github.com/intel-iot-devkit/sample-videos/raw/master/people-detection.mp4

--2026-10-20 00:08:41--  https://github.com/intel-iot-devkit/sample-videos/raw/master/people-detection.mp4
Resolving github.com (github.com)... 20.205.243.166
Connecting to github.com (github.com)|20.205.243.166|:443... connected.
HTTP request sent, awaiting response... 302 Found
Location: https://raw.githubusercontent.com/intel-iot-devkit/sample-videos/master/people-detection.mp4 [following]
--2026-10-20 00:08:42--  https://raw.githubusercontent.com/intel-iot-devkit/sample-videos/master/people-detection.mp4
Resolving raw.githubusercontent.com (raw.githubusercontent.com)... 185.199.108.133, 185.199.109.133, 185.199.110.133, ...
Connecting to raw.githubusercontent.com (raw.githubusercontent.com)|185.199.108.133|:443... connected.
HTTP request sent, awaiting response... 200 OK
Length: 5482579 (5.2M) [application/octet-stream]
Saving to: ‘people-detection.mp4’

people-detection.mp 100%[===================>]   5.23M  --.-KB/s    in 0.02s   

2026-10-20 00:08:42 (321 MB/s) - ‘people-detecti

In [4]:
# ==========================================
# Phase 2: YOLO26 Tracking Execution
# ==========================================
from ultralytics import YOLO

# Instantiate the SOTA YOLO26 nano model.
# Its NMS-free architecture ensures deterministic, low-latency tracking suitable for edge deployment.
model = YOLO("yolo26n.pt")

# Initialize video capture using OpenCV
cap = cv2.VideoCapture("people-detection.mp4")

# Safety check!
if not cap.isOpened():
    raise ValueError(f"CRITICAL ERROR: OpenCV could not open 'people-detection.mp4'. The file is missing or corrupted.")

width  = int(cap.get(cv2.CAP_PROP_FRAME_WIDTH))
height = int(cap.get(cv2.CAP_PROP_FRAME_HEIGHT))
fps = int(cap.get(cv2.CAP_PROP_FPS))

# Second safety check!
if width == 0 or height == 0:
    raise ValueError("CRITICAL ERROR: Video dimensions are 0x0. The video stream is invalid.")

output_path_yolo = "yolo26_tracking_output.mp4"
fourcc = cv2.VideoWriter_fourcc(*'mp4v')
out_yolo = cv2.VideoWriter(output_path_yolo, fourcc, fps, (width, height))

# Initialize a default dictionary to persistently store mathematical trajectory history
track_history = defaultdict(list)

print("Executing YOLO26 spatio-temporal tracking pipeline...")
while cap.isOpened():
    success, frame = cap.read()
    if not success:
        break

    # Extract the first (and only) Results object from the returned list
    results = model.track(frame, persist=True, tracker="botsort.yaml", verbose=False)[0]

    # 'results' is a Results object
    if results.boxes.id is not None:
        boxes = results.boxes.xywh.cpu() # x_center, y_center, width, height
        track_ids = results.boxes.id.int().cpu().tolist()

        # Superimpose the fundamental bounding boxes onto the frame tensor
        annotated_frame = results.plot()

        # Iterate through detected IDs to draw historical trajectory lines
        for box, track_id in zip(boxes, track_ids):
            x, y, w, h = box
            track = track_history[track_id]
            track.append((float(x), float(y))) # Append current spatial center point

            # Constrain the trajectory visualizer to the last 30 frames to prevent tensor memory bloat
            if len(track) > 30:
                track.pop(0)

            # Utilize OpenCV to render the trajectory polyline
            points = np.hstack(track).astype(np.int32).reshape((-1, 1, 2))
            cv2.polylines(annotated_frame, [points], isClosed=False, color=(0, 255, 255), thickness=2)

        out_yolo.write(annotated_frame)
    else:
        out_yolo.write(frame)

cap.release()
out_yolo.release()
print(f"YOLO26 Tracking finalized. Video synthesized to {output_path_yolo}")

Creating new Ultralytics Settings v0.0.8 file ✅ 
View Ultralytics Settings with 'yolo settings' or at '/root/.config/Ultralytics/settings.json'
Update Settings with 'yolo settings key=value', i.e. 'yolo settings runs_dir=path/to/dir'. For help see https://docs.ultralytics.com/usage/settings.
Executing YOLO26 spatio-temporal tracking pipeline...
requirements: Ultralytics requirement ['lap>=0.5.12'] not found, attempting AutoUpdate...
Using Python 3.13.15 environment at: /usr
Resolved 2 packages in 170ms
Prepared 1 package in 23ms
Installed 1 package in 1ms
 + lap==0.5.13

requirements: AutoUpdate success ✅ 0.5s
WARNING ⚠️ requirements: Restart runtime or rerun command for updates to take effect

YOLO26 Tracking finalized. Video synthesized to yolo26_tracking_output.mp4


In [5]:
!ls

people-detection.mp4  sample_data  yolo26n.pt  yolo26_tracking_output.mp4


In [6]:
!ffmpeg -i yolo26_tracking_output.mp4 -vcodec libx264 compressed_yolo26_tracking_output.mp4

ffmpeg version 6.1.1-3ubuntu5 Copyright (c) 2000-2023 the FFmpeg developers
  built with gcc 13 (Ubuntu 13.2.0-23ubuntu3)
  configuration: --prefix=/usr --extra-version=3ubuntu5 --toolchain=hardened --libdir=/usr/lib/x86_64-linux-gnu --incdir=/usr/include/x86_64-linux-gnu --arch=amd64 --enable-gpl --disable-stripping --disable-omx --enable-gnutls --enable-libaom --enable-libass --enable-libbs2b --enable-libcaca --enable-libcdio --enable-libcodec2 --enable-libdav1d --enable-libflite --enable-libfontconfig --enable-libfreetype --enable-libfribidi --enable-libglslang --enable-libgme --enable-libgsm --enable-libharfbuzz --enable-libmp3lame --enable-libmysofa --enable-libopenjpeg --enable-libopenmpt --enable-libopus --enable-librubberband --enable-libshine --enable-libsnappy --enable-libsoxr --enable-libspeex --enable-libtheora --enable-libtwolame --enable-libvidstab --enable-libvorbis --enable-libvpx --enable-libwebp --enable-libx265 --enable-libxml2 --enable-libxvid --enable-libzimg --ena

In [7]:
# Read the binary stream and encode to base64 for direct browser injection
mp4_data = open("compressed_yolo26_tracking_output.mp4",'rb').read()
data_url = "data:video/mp4;base64," + b64encode(mp4_data).decode()

# Render utilizing IPython display utilities
display(HTML(f"""<video width=800 controls><source src="{data_url}" type="video/mp4"></video>"""))

In [8]:
# ==========================================
# Phase 3: Composite Open-Vocabulary Segmentation
# (YOLO-World + SAM 2 Pipeline)
# ==========================================
from ultralytics import YOLOWorld, SAM
import cv2
import numpy as np

print("Loading Open-Vocabulary Detector and Segmentation models...")

# 1. Initialize YOLO-World (Vision-Language Zero-Shot Detector)
# This handles the "Text Prompt" portion of the pipeline.
yolo_world = YOLOWorld("yolov8s-worldv2.pt")

# Define our open-vocabulary concepts. YOLO-World will dynamically compile these into its detection head.
# You can change these to anything you want to detect in the video!
custom_prompts = ["person"]
yolo_world.set_classes(custom_prompts)

# 2. Initialize SAM 2 (Segment Anything Model 2)
# We use the nano version for fast inference in Colab.
# This handles the pixel-level masking based on the bounding boxes provided by YOLO-World.
sam_model = SAM("sam2.1_t.pt")

# 3. Setup Video Stream
video_path = "people-detection.mp4"
cap = cv2.VideoCapture(video_path)

if not cap.isOpened():
    raise ValueError(f"CRITICAL ERROR: OpenCV could not open {video_path}.")

width  = int(cap.get(cv2.CAP_PROP_FRAME_WIDTH))
height = int(cap.get(cv2.CAP_PROP_FRAME_HEIGHT))
fps = int(cap.get(cv2.CAP_PROP_FPS))

output_path_composite = "composite_segmentation_output.mp4"
fourcc = cv2.VideoWriter_fourcc(*'mp4v')
out_composite = cv2.VideoWriter(output_path_composite, fourcc, fps, (width, height))

print(f"Executing YOLO-World + SAM 2 Pipeline on concepts: {custom_prompts}...")

frame_count = 0
while cap.isOpened():
    success, frame = cap.read()
    if not success:
        break

    frame_count += 1
    if frame_count % 30 == 0:
        print(f"Processing frame {frame_count}...")

    # Step A: Concept Grounding (YOLO-World)
    # We use persist=True to maintain tracking IDs across frames
    yolo_results = yolo_world.track(frame, persist=True, verbose=False)[0]

    # Step B: Extract Spatial Coordinates
    # SAM requires bounding boxes in xyxy format (xmin, ymin, xmax, ymax)
    if yolo_results.boxes.id is not None and len(yolo_results.boxes.xyxy) > 0:
        boxes_xyxy = yolo_results.boxes.xyxy.cpu().numpy()

        # Step C: Prompted Segmentation (SAM 2)
        # We pass the bounding boxes directly to SAM as visual prompts
        sam_results = sam_model(frame, bboxes=boxes_xyxy, verbose=False)[0]

        # Superimpose the generated alpha-blended masks onto the frame
        # We also draw the bounding boxes and labels from YOLO-World for clarity
        annotated_frame = sam_results.plot(boxes=False) # Plot SAM masks
        annotated_frame = yolo_results.plot(img=annotated_frame) # Overlay YOLO boxes/labels

        out_composite.write(annotated_frame)
    else:
        # If YOLO-World didn't find our text prompts in this frame, write the raw frame
        out_composite.write(frame)

cap.release()
out_composite.release()
print(f"Pipeline finalized. Video synthesized to {output_path_composite}")



Loading Open-Vocabulary Detector and Segmentation models...
requirements: Ultralytics requirement ['git+https://github.com/ultralytics/CLIP.git'] not found, attempting AutoUpdate...
Using Python 3.13.15 environment at: /usr
Resolved 37 packages in 526ms
Prepared 2 packages in 2.44s
Installed 2 packages in 2ms
 + clip==1.0 (from git+https://github.com/ultralytics/CLIP.git@7ffa84b3bfa40c42ecc1c77147a855e69cb2dd40)
 + ftfy==6.3.1

requirements: AutoUpdate success ✅ 3.1s
WARNING ⚠️ requirements: Restart runtime or rerun command for updates to take effect



100%|███████████████████████████████████████| 338M/338M [00:04<00:00, 75.7MiB/s]


Executing YOLO-World + SAM 2 Pipeline on concepts: ['person']...
Processing frame 30...
Processing frame 60...
Processing frame 90...
Processing frame 120...
Processing frame 150...
Processing frame 180...
Processing frame 210...
Processing frame 240...
Processing frame 270...
Processing frame 300...
Processing frame 330...
Processing frame 360...
Processing frame 390...
Processing frame 420...
Processing frame 450...
Processing frame 480...
Processing frame 510...
Processing frame 540...
Processing frame 570...
Pipeline finalized. Video synthesized to composite_segmentation_output.mp4


In [9]:
!ffmpeg -y -i composite_segmentation_output.mp4 -vcodec libx264 compressed_composite_segmentation_output.mp4

ffmpeg version 6.1.1-3ubuntu5 Copyright (c) 2000-2023 the FFmpeg developers
  built with gcc 13 (Ubuntu 13.2.0-23ubuntu3)
  configuration: --prefix=/usr --extra-version=3ubuntu5 --toolchain=hardened --libdir=/usr/lib/x86_64-linux-gnu --incdir=/usr/include/x86_64-linux-gnu --arch=amd64 --enable-gpl --disable-stripping --disable-omx --enable-gnutls --enable-libaom --enable-libass --enable-libbs2b --enable-libcaca --enable-libcdio --enable-libcodec2 --enable-libdav1d --enable-libflite --enable-libfontconfig --enable-libfreetype --enable-libfribidi --enable-libglslang --enable-libgme --enable-libgsm --enable-libharfbuzz --enable-libmp3lame --enable-libmysofa --enable-libopenjpeg --enable-libopenmpt --enable-libopus --enable-librubberband --enable-libshine --enable-libsnappy --enable-libsoxr --enable-libspeex --enable-libtheora --enable-libtwolame --enable-libvidstab --enable-libvorbis --enable-libvpx --enable-libwebp --enable-libx265 --enable-libxml2 --enable-libxvid --enable-libzimg --ena

In [10]:
# Read the binary stream and encode to base64 for direct browser injection
mp4_data = open("compressed_composite_segmentation_output.mp4",'rb').read()
data_url = "data:video/mp4;base64," + b64encode(mp4_data).decode()

# Render utilizing IPython display utilities
display(HTML(f"""<video width=800 controls><source src="{data_url}" type="video/mp4"></video>"""))

**Actividad**

1. a) Corra Yolo con al menos 3 nuevos videos
 b) detecte los tipos de error más usuales. Describa si los errores hacen referencia a la detección o si hacen referencia a la asignación de identificadores.
 c) relacione con los conceptos de la clase

2. a) Corra el pipeline de SAM para al menos 3 videos (pueden ser mismos videos de la actividad 1). En alguno solicite tracking de un objeto únicos, en otro solicite el tracking de un objeto que sea múltiple (ej: 2 personas que aparecen simultáneamente en el video), y en otro solicite al modelo que haga tracking de más de un prompt simultáneamente.
b) Analice los resultados y comente los tipos de error que identificó. Describa si los errores hacen referencia a la detección o si hacen referencia a la asignación de identificadores.
 c) Relacione con los conceptos de la clase

## Actividad 1

Primero, vamos a modularizar el tracking con YOLO

In [11]:
def realizar_tracking_yolo(path_to_video, output_path_yolo="yolo26_tracking_output.mp4"):
    # Initialize video capture using OpenCV
    cap = cv2.VideoCapture(path_to_video)

    # Safety check!
    if not cap.isOpened():
        raise ValueError(f"CRITICAL ERROR: OpenCV could not open '{path_to_video}'. The file is missing or corrupted.")

    width  = int(cap.get(cv2.CAP_PROP_FRAME_WIDTH))
    height = int(cap.get(cv2.CAP_PROP_FRAME_HEIGHT))
    fps = int(cap.get(cv2.CAP_PROP_FPS))

    # Second safety check!
    if width == 0 or height == 0:
        raise ValueError("CRITICAL ERROR: Video dimensions are 0x0. The video stream is invalid.")

    fourcc = cv2.VideoWriter_fourcc(*'mp4v')
    out_yolo = cv2.VideoWriter(output_path_yolo, fourcc, fps, (width, height))

    # Initialize a default dictionary to persistently store mathematical trajectory history
    track_history = defaultdict(list)

    print("Executing YOLO26 spatio-temporal tracking pipeline...")
    while cap.isOpened():
        success, frame = cap.read()
        if not success:
            break

        # Extract the first (and only) Results object from the returned list
        results = model.track(frame, persist=True, tracker="botsort.yaml", verbose=False)[0]

        # 'results' is a Results object
        if results.boxes.id is not None:
            boxes = results.boxes.xywh.cpu() # x_center, y_center, width, height
            track_ids = results.boxes.id.int().cpu().tolist()

            # Superimpose the fundamental bounding boxes onto the frame tensor
            annotated_frame = results.plot()

            # Iterate through detected IDs to draw historical trajectory lines
            for box, track_id in zip(boxes, track_ids):
                x, y, w, h = box
                track = track_history[track_id]
                track.append((float(x), float(y))) # Append current spatial center point

                # Constrain the trajectory visualizer to the last 30 frames to prevent tensor memory bloat
                if len(track) > 30:
                    track.pop(0)

                # Utilize OpenCV to render the trajectory polyline
                points = np.hstack(track).astype(np.int32).reshape((-1, 1, 2))
                cv2.polylines(annotated_frame, [points], isClosed=False, color=(0, 255, 255), thickness=2)

            out_yolo.write(annotated_frame)
        else:
            out_yolo.write(frame)

    cap.release()
    out_yolo.release()
    print(f"YOLO26 Tracking finalized. Video synthesized to {output_path_yolo}")

def visualizar_video(path):
    # Read the binary stream and encode to base64 for direct browser injection
    mp4_data = open(path,'rb').read()
    data_url = "data:video/mp4;base64," + b64encode(mp4_data).decode()

    # Render utilizing IPython display utilities
    display(HTML(f"""<video width=800 controls><source src="{data_url}" type="video/mp4"></video>"""))

In [12]:
!wget https://github.com/intel-iot-devkit/sample-videos/raw/master/bottle-detection.mp4
nombre_archivo = "bottle-detection.mp4"
output_path = "bottle-tracking-output.mp4"
output_path_compressed = f"compressed-{output_path}"

--2026-10-20 00:10:37--  https://github.com/intel-iot-devkit/sample-videos/raw/master/bottle-detection.mp4
Resolving github.com (github.com)... 20.205.243.166
Connecting to github.com (github.com)|20.205.243.166|:443... connected.
HTTP request sent, awaiting response... 302 Found
Location: https://raw.githubusercontent.com/intel-iot-devkit/sample-videos/master/bottle-detection.mp4 [following]
--2026-10-20 00:10:38--  https://raw.githubusercontent.com/intel-iot-devkit/sample-videos/master/bottle-detection.mp4
Resolving raw.githubusercontent.com (raw.githubusercontent.com)... 185.199.108.133, 185.199.109.133, 185.199.110.133, ...
Connecting to raw.githubusercontent.com (raw.githubusercontent.com)|185.199.108.133|:443... connected.
HTTP request sent, awaiting response... 200 OK
Length: 504961 (493K) [application/octet-stream]
Saving to: ‘bottle-detection.mp4’

bottle-detection.mp 100%[===================>] 493.13K  --.-KB/s    in 0.006s  

2026-10-20 00:10:38 (86.0 MB/s) - ‘bottle-detecti

In [13]:
realizar_tracking_yolo(nombre_archivo, output_path_yolo=output_path)

Executing YOLO26 spatio-temporal tracking pipeline...
WARNING ⚠️ GMC failed, falling back to identity: OpenCV(4.14.0) /io/opencv/modules/video/src/lkpyramid.cpp:1338: error: (-215:Assertion failed) prevPyr[level * lvlStep1].size() == nextPyr[level * lvlStep2].size() in function 'calc'

WARNING ⚠️ GMC failed, falling back to identity: OpenCV(4.14.0) /io/opencv/modules/video/src/lkpyramid.cpp:1338: error: (-215:Assertion failed) prevPyr[level * lvlStep1].size() == nextPyr[level * lvlStep2].size() in function 'calc'

WARNING ⚠️ GMC failed, falling back to identity: OpenCV(4.14.0) /io/opencv/modules/video/src/lkpyramid.cpp:1338: error: (-215:Assertion failed) prevPyr[level * lvlStep1].size() == nextPyr[level * lvlStep2].size() in function 'calc'

WARNING ⚠️ GMC failed, falling back to identity: OpenCV(4.14.0) /io/opencv/modules/video/src/lkpyramid.cpp:1338: error: (-215:Assertion failed) prevPyr[level * lvlStep1].size() == nextPyr[level * lvlStep2].size() in function 'calc'

WARNING ⚠️ GMC

In [14]:
!ffmpeg -i {output_path} -vcodec libx264 {output_path_compressed}
visualizar_video(output_path_compressed)

ffmpeg version 6.1.1-3ubuntu5 Copyright (c) 2000-2023 the FFmpeg developers
  built with gcc 13 (Ubuntu 13.2.0-23ubuntu3)
  configuration: --prefix=/usr --extra-version=3ubuntu5 --toolchain=hardened --libdir=/usr/lib/x86_64-linux-gnu --incdir=/usr/include/x86_64-linux-gnu --arch=amd64 --enable-gpl --disable-stripping --disable-omx --enable-gnutls --enable-libaom --enable-libass --enable-libbs2b --enable-libcaca --enable-libcdio --enable-libcodec2 --enable-libdav1d --enable-libflite --enable-libfontconfig --enable-libfreetype --enable-libfribidi --enable-libglslang --enable-libgme --enable-libgsm --enable-libharfbuzz --enable-libmp3lame --enable-libmysofa --enable-libopenjpeg --enable-libopenmpt --enable-libopus --enable-librubberband --enable-libshine --enable-libsnappy --enable-libsoxr --enable-libspeex --enable-libtheora --enable-libtwolame --enable-libvidstab --enable-libvorbis --enable-libvpx --enable-libwebp --enable-libx265 --enable-libxml2 --enable-libxvid --enable-libzimg --ena

El modelo YOLO efectivamente está identificando correctamente los objetos, detectando únicamente botellas y personas (lo único que aparece en el video). Sin embargo, es posible observar errores al asignar los identificadores de cada objeto. Por ejemplo, en la botella de la izquierda inicialmente se le asigna id = 33, que luego de salir de escena y ser reintroducida (asumiendo que es la misma botella) se la asigna el id = 42. Si obviamos las botellas, que efectivamente podrían ser cambiadas cuando salgan de escena,  al ver la mano izquierda de la persona que las levanta inicia con id = 39 y cuando vuelve a escena vuelve con id = 44. De hecho, luego le asigna id = 50 y 52 a la misma mano.

In [15]:
!wget https://github.com/intel-iot-devkit/sample-videos/raw/master/bolt-detection.mp4
nombre_archivo = "bolt-detection.mp4"
output_path = "bolt-detection-output.mp4"
output_path_compressed = f"compressed-{output_path}"

--2026-10-20 00:11:15--  https://github.com/intel-iot-devkit/sample-videos/raw/master/bolt-detection.mp4
Resolving github.com (github.com)... 20.205.243.166
Connecting to github.com (github.com)|20.205.243.166|:443... connected.
HTTP request sent, awaiting response... 302 Found
Location: https://raw.githubusercontent.com/intel-iot-devkit/sample-videos/master/bolt-detection.mp4 [following]
--2026-10-20 00:11:16--  https://raw.githubusercontent.com/intel-iot-devkit/sample-videos/master/bolt-detection.mp4
Resolving raw.githubusercontent.com (raw.githubusercontent.com)... 185.199.108.133, 185.199.109.133, 185.199.110.133, ...
Connecting to raw.githubusercontent.com (raw.githubusercontent.com)|185.199.108.133|:443... connected.
HTTP request sent, awaiting response... 200 OK
Length: 9285374 (8.9M) [application/octet-stream]
Saving to: ‘bolt-detection.mp4’

bolt-detection.mp4  100%[===================>]   8.85M  --.-KB/s    in 0.02s   

2026-10-20 00:11:17 (448 MB/s) - ‘bolt-detection.mp4’ sa

In [16]:
realizar_tracking_yolo(nombre_archivo, output_path_yolo=output_path)

Executing YOLO26 spatio-temporal tracking pipeline...
WARNING ⚠️ GMC failed, falling back to identity: OpenCV(4.14.0) /io/opencv/modules/video/src/lkpyramid.cpp:1338: error: (-215:Assertion failed) prevPyr[level * lvlStep1].size() == nextPyr[level * lvlStep2].size() in function 'calc'

WARNING ⚠️ GMC failed, falling back to identity: OpenCV(4.14.0) /io/opencv/modules/video/src/lkpyramid.cpp:1338: error: (-215:Assertion failed) prevPyr[level * lvlStep1].size() == nextPyr[level * lvlStep2].size() in function 'calc'

WARNING ⚠️ GMC failed, falling back to identity: OpenCV(4.14.0) /io/opencv/modules/video/src/lkpyramid.cpp:1338: error: (-215:Assertion failed) prevPyr[level * lvlStep1].size() == nextPyr[level * lvlStep2].size() in function 'calc'

WARNING ⚠️ GMC failed, falling back to identity: OpenCV(4.14.0) /io/opencv/modules/video/src/lkpyramid.cpp:1338: error: (-215:Assertion failed) prevPyr[level * lvlStep1].size() == nextPyr[level * lvlStep2].size() in function 'calc'

WARNING ⚠️ GMC

In [17]:
!ffmpeg -i {output_path} -vcodec libx264 {output_path_compressed}
visualizar_video(output_path_compressed)

ffmpeg version 6.1.1-3ubuntu5 Copyright (c) 2000-2023 the FFmpeg developers
  built with gcc 13 (Ubuntu 13.2.0-23ubuntu3)
  configuration: --prefix=/usr --extra-version=3ubuntu5 --toolchain=hardened --libdir=/usr/lib/x86_64-linux-gnu --incdir=/usr/include/x86_64-linux-gnu --arch=amd64 --enable-gpl --disable-stripping --disable-omx --enable-gnutls --enable-libaom --enable-libass --enable-libbs2b --enable-libcaca --enable-libcdio --enable-libcodec2 --enable-libdav1d --enable-libflite --enable-libfontconfig --enable-libfreetype --enable-libfribidi --enable-libglslang --enable-libgme --enable-libgsm --enable-libharfbuzz --enable-libmp3lame --enable-libmysofa --enable-libopenjpeg --enable-libopenmpt --enable-libopus --enable-librubberband --enable-libshine --enable-libsnappy --enable-libsoxr --enable-libspeex --enable-libtheora --enable-libtwolame --enable-libvidstab --enable-libvorbis --enable-libvpx --enable-libwebp --enable-libx265 --enable-libxml2 --enable-libxvid --enable-libzimg --ena

In [18]:
!wget https://github.com/intel-iot-devkit/sample-videos/raw/master/person-bicycle-car-detection.mp4
nombre_archivo = "person-bicycle-car-detection.mp4"
output_path = "person-bicycle-car-detection-output.mp4"
output_path_compressed = f"compressed-{output_path}"

--2026-10-20 00:12:24--  https://github.com/intel-iot-devkit/sample-videos/raw/master/person-bicycle-car-detection.mp4
Resolving github.com (github.com)... 20.205.243.166
Connecting to github.com (github.com)|20.205.243.166|:443... connected.
HTTP request sent, awaiting response... 302 Found
Location: https://raw.githubusercontent.com/intel-iot-devkit/sample-videos/master/person-bicycle-car-detection.mp4 [following]
--2026-10-20 00:12:25--  https://raw.githubusercontent.com/intel-iot-devkit/sample-videos/master/person-bicycle-car-detection.mp4
Resolving raw.githubusercontent.com (raw.githubusercontent.com)... 185.199.108.133, 185.199.109.133, 185.199.110.133, ...
Connecting to raw.githubusercontent.com (raw.githubusercontent.com)|185.199.108.133|:443... connected.
HTTP request sent, awaiting response... 200 OK
Length: 6031199 (5.8M) [application/octet-stream]
Saving to: ‘person-bicycle-car-detection.mp4’

person-bicycle-car- 100%[===================>]   5.75M  --.-KB/s    in 0.01s   



In [19]:
realizar_tracking_yolo(nombre_archivo, output_path_yolo=output_path)

Executing YOLO26 spatio-temporal tracking pipeline...
YOLO26 Tracking finalized. Video synthesized to person-bicycle-car-detection-output.mp4


In [20]:
!ffmpeg -i {output_path} -vcodec libx264 {output_path_compressed}
visualizar_video(output_path_compressed)

ffmpeg version 6.1.1-3ubuntu5 Copyright (c) 2000-2023 the FFmpeg developers
  built with gcc 13 (Ubuntu 13.2.0-23ubuntu3)
  configuration: --prefix=/usr --extra-version=3ubuntu5 --toolchain=hardened --libdir=/usr/lib/x86_64-linux-gnu --incdir=/usr/include/x86_64-linux-gnu --arch=amd64 --enable-gpl --disable-stripping --disable-omx --enable-gnutls --enable-libaom --enable-libass --enable-libbs2b --enable-libcaca --enable-libcdio --enable-libcodec2 --enable-libdav1d --enable-libflite --enable-libfontconfig --enable-libfreetype --enable-libfribidi --enable-libglslang --enable-libgme --enable-libgsm --enable-libharfbuzz --enable-libmp3lame --enable-libmysofa --enable-libopenjpeg --enable-libopenmpt --enable-libopus --enable-librubberband --enable-libshine --enable-libsnappy --enable-libsoxr --enable-libspeex --enable-libtheora --enable-libtwolame --enable-libvidstab --enable-libvorbis --enable-libvpx --enable-libwebp --enable-libx265 --enable-libxml2 --enable-libxvid --enable-libzimg --ena

## Actividad 2

In [25]:
def cargar_modelos(custom_prompts, detector_weights="yolov8s-worldv2.pt", sam_weights="sam2.1_t.pt"):
    print("Loading Open Vocabulary Detector and Segmentation models...")
 
    # 1. Initialize YOLO World (Vision Language Zero Shot Detector)
    # This handles the text prompt portion of the pipeline.
    yolo_world = YOLOWorld(detector_weights)
 
    # Define the open vocabulary concepts. YOLO World compiles these into its detection head.
    # You can change these to anything you want to detect in the video.
    yolo_world.set_classes(custom_prompts)
 
    # 2. Initialize SAM 2 (Segment Anything Model 2)
    # The nano version is used for fast inference in Colab.
    # This handles the pixel level masking based on the boxes provided by YOLO World.
    sam_model = SAM(sam_weights)
 
    return yolo_world, sam_model


In [26]:
def realizar_tracking_sam(video_path, yolo_world, sam_model, output_path_composite="composite_segmentation_output.mp4"):
    # Reset the tracker so IDs from a previous video do not carry over
    yolo_world.predictor = None
 
    # 3. Setup video stream
    cap = cv2.VideoCapture(video_path)
 
    if not cap.isOpened():
        raise ValueError(f"CRITICAL ERROR OpenCV could not open {video_path}.")
 
    width = int(cap.get(cv2.CAP_PROP_FRAME_WIDTH))
    height = int(cap.get(cv2.CAP_PROP_FRAME_HEIGHT))
    fps = cap.get(cv2.CAP_PROP_FPS) or 30.0  # kept as float to respect rates like 29.97
 
    fourcc = cv2.VideoWriter_fourcc(*'mp4v')
    out_composite = cv2.VideoWriter(output_path_composite, fourcc, fps, (width, height))
 
    print(f"Executing YOLO World + SAM 2 Pipeline on {video_path}...")
 
    frame_count = 0
    try:
        while cap.isOpened():
            success, frame = cap.read()
            if not success:
                break
 
            frame_count += 1
            if frame_count % 30 == 0:
                print(f"Processing frame {frame_count}...")
 
            # Step A, concept grounding with YOLO World
            # persist=True maintains tracking IDs across frames
            yolo_results = yolo_world.track(frame, persist=True, verbose=False)[0]
 
            # Step B, extract spatial coordinates
            # SAM requires bounding boxes in xyxy format (xmin, ymin, xmax, ymax)
            if yolo_results.boxes.id is not None and len(yolo_results.boxes.xyxy) > 0:
                boxes_xyxy = yolo_results.boxes.xyxy.cpu().numpy()
 
                # Step C, prompted segmentation with SAM 2
                # The boxes are passed directly to SAM as visual prompts
                sam_results = sam_model(frame, bboxes=boxes_xyxy, verbose=False)[0]
 
                # Superimpose the alpha blended masks onto the frame
                # Boxes and labels from YOLO World are drawn on top for clarity
                annotated_frame = sam_results.plot(boxes=False)  # Plot SAM masks
                annotated_frame = yolo_results.plot(img=annotated_frame)  # Overlay YOLO boxes and labels
 
                out_composite.write(annotated_frame)
            else:
                # If YOLO World did not find the text prompts in this frame, write the raw frame
                out_composite.write(frame)
    finally:
        # Always release resources, even if a frame fails midway
        cap.release()
        out_composite.release()
 
    print(f"Pipeline finalized. Video synthesized to {output_path_composite}")
    return output_path_composite



In [27]:
yolo_world, sam_model = cargar_modelos(["bottle", "person"])

Loading Open Vocabulary Detector and Segmentation models...


In [28]:
realizar_tracking_sam("bottle-detection.mp4", yolo_world, sam_model, "sam-composite-bottle-detection.mp4")

Executing YOLO World + SAM 2 Pipeline on bottle-detection.mp4...
Processing frame 30...
Processing frame 60...
Processing frame 90...
Processing frame 120...
Processing frame 150...
Processing frame 180...
Processing frame 210...
Processing frame 240...
Processing frame 270...
Processing frame 300...
Processing frame 330...
Processing frame 360...
Processing frame 390...
Processing frame 420...
Processing frame 450...
Processing frame 480...
Processing frame 510...
Processing frame 540...
Processing frame 570...
Processing frame 600...
Processing frame 630...
Processing frame 660...
Processing frame 690...
Processing frame 720...
Processing frame 750...
Processing frame 780...
Processing frame 810...
Processing frame 840...
Processing frame 870...
Processing frame 900...
Processing frame 930...
Processing frame 960...
Processing frame 990...
Processing frame 1020...
Processing frame 1050...
Processing frame 1080...
Processing frame 1110...
Processing frame 1140...
Processing frame 1170

'sam-composite-bottle-detection.mp4'

In [31]:
!ffmpeg -y -i sam-composite-bottle-detection.mp4 -vcodec libx264 compressed_sam-composite-bottle-detection.mp4

ffmpeg version 6.1.1-3ubuntu5 Copyright (c) 2000-2023 the FFmpeg developers
  built with gcc 13 (Ubuntu 13.2.0-23ubuntu3)
  configuration: --prefix=/usr --extra-version=3ubuntu5 --toolchain=hardened --libdir=/usr/lib/x86_64-linux-gnu --incdir=/usr/include/x86_64-linux-gnu --arch=amd64 --enable-gpl --disable-stripping --disable-omx --enable-gnutls --enable-libaom --enable-libass --enable-libbs2b --enable-libcaca --enable-libcdio --enable-libcodec2 --enable-libdav1d --enable-libflite --enable-libfontconfig --enable-libfreetype --enable-libfribidi --enable-libglslang --enable-libgme --enable-libgsm --enable-libharfbuzz --enable-libmp3lame --enable-libmysofa --enable-libopenjpeg --enable-libopenmpt --enable-libopus --enable-librubberband --enable-libshine --enable-libsnappy --enable-libsoxr --enable-libspeex --enable-libtheora --enable-libtwolame --enable-libvidstab --enable-libvorbis --enable-libvpx --enable-libwebp --enable-libx265 --enable-libxml2 --enable-libxvid --enable-libzimg --ena

In [32]:
# Read the binary stream and encode to base64 for direct browser injection
mp4_data = open("compressed_sam-composite-bottle-detection.mp4",'rb').read()
data_url = "data:video/mp4;base64," + b64encode(mp4_data).decode()

# Render utilizing IPython display utilities
display(HTML(f"""<video width=800 controls><source src="{data_url}" type="video/mp4"></video>"""))

In [37]:
yolo_world, sam_model = cargar_modelos(["bolts"])
realizar_tracking_sam("bolt-detection.mp4", yolo_world, sam_model, "sam-composite-bolt-detection.mp4")


Loading Open Vocabulary Detector and Segmentation models...
Executing YOLO World + SAM 2 Pipeline on bolt-detection.mp4...
Processing frame 30...
Processing frame 60...
Processing frame 90...
Processing frame 120...
Processing frame 150...
Processing frame 180...
Processing frame 210...
Processing frame 240...
Processing frame 270...
Processing frame 300...
Processing frame 330...
Processing frame 360...
Processing frame 390...
Processing frame 420...
Processing frame 450...
Processing frame 480...
Processing frame 510...
Processing frame 540...
Processing frame 570...
Processing frame 600...
Processing frame 630...
Processing frame 660...
Processing frame 690...
Processing frame 720...
Processing frame 750...
Processing frame 780...
Processing frame 810...
Processing frame 840...
Processing frame 870...
Processing frame 900...
Pipeline finalized. Video synthesized to sam-composite-bolt-detection.mp4


'sam-composite-bolt-detection.mp4'

In [38]:
!ffmpeg -y -i sam-composite-bolt-detection.mp4 -vcodec libx264 compressed_sam-composite-bolt-detection.mp4

ffmpeg version 6.1.1-3ubuntu5 Copyright (c) 2000-2023 the FFmpeg developers
  built with gcc 13 (Ubuntu 13.2.0-23ubuntu3)
  configuration: --prefix=/usr --extra-version=3ubuntu5 --toolchain=hardened --libdir=/usr/lib/x86_64-linux-gnu --incdir=/usr/include/x86_64-linux-gnu --arch=amd64 --enable-gpl --disable-stripping --disable-omx --enable-gnutls --enable-libaom --enable-libass --enable-libbs2b --enable-libcaca --enable-libcdio --enable-libcodec2 --enable-libdav1d --enable-libflite --enable-libfontconfig --enable-libfreetype --enable-libfribidi --enable-libglslang --enable-libgme --enable-libgsm --enable-libharfbuzz --enable-libmp3lame --enable-libmysofa --enable-libopenjpeg --enable-libopenmpt --enable-libopus --enable-librubberband --enable-libshine --enable-libsnappy --enable-libsoxr --enable-libspeex --enable-libtheora --enable-libtwolame --enable-libvidstab --enable-libvorbis --enable-libvpx --enable-libwebp --enable-libx265 --enable-libxml2 --enable-libxvid --enable-libzimg --ena

In [39]:
# Read the binary stream and encode to base64 for direct browser injection
mp4_data = open("compressed_sam-composite-bolt-detection.mp4",'rb').read()
data_url = "data:video/mp4;base64," + b64encode(mp4_data).decode()

# Render utilizing IPython display utilities
display(HTML(f"""<video width=800 controls><source src="{data_url}" type="video/mp4"></video>"""))

In [30]:
yolo_world, sam_model = cargar_modelos(["person", "bicycle", "car"])
realizar_tracking_sam("person-bicycle-car-detection.mp4", yolo_world, sam_model, "sam-composite-person-bicycle-car-detection.mp4")

Loading Open Vocabulary Detector and Segmentation models...
Executing YOLO World + SAM 2 Pipeline on person-bicycle-car-detection.mp4...
Processing frame 30...
Processing frame 60...
Processing frame 90...
Processing frame 120...
Processing frame 150...
Processing frame 180...
Processing frame 210...
Processing frame 240...
Processing frame 270...
Processing frame 300...
Processing frame 330...
Processing frame 360...
Processing frame 390...
Processing frame 420...
Processing frame 450...
Processing frame 480...
Processing frame 510...
Processing frame 540...
Processing frame 570...
Processing frame 600...
Processing frame 630...
Pipeline finalized. Video synthesized to sam-composite-person-bicycle-car-detection.mp4


'sam-composite-person-bicycle-car-detection.mp4'

In [35]:
!ffmpeg -y -i sam-composite-person-bicycle-car-detection.mp4 -vcodec libx264 compressed_sam-composite-person-bicycle-car-detection.mp4

ffmpeg version 6.1.1-3ubuntu5 Copyright (c) 2000-2023 the FFmpeg developers
  built with gcc 13 (Ubuntu 13.2.0-23ubuntu3)
  configuration: --prefix=/usr --extra-version=3ubuntu5 --toolchain=hardened --libdir=/usr/lib/x86_64-linux-gnu --incdir=/usr/include/x86_64-linux-gnu --arch=amd64 --enable-gpl --disable-stripping --disable-omx --enable-gnutls --enable-libaom --enable-libass --enable-libbs2b --enable-libcaca --enable-libcdio --enable-libcodec2 --enable-libdav1d --enable-libflite --enable-libfontconfig --enable-libfreetype --enable-libfribidi --enable-libglslang --enable-libgme --enable-libgsm --enable-libharfbuzz --enable-libmp3lame --enable-libmysofa --enable-libopenjpeg --enable-libopenmpt --enable-libopus --enable-librubberband --enable-libshine --enable-libsnappy --enable-libsoxr --enable-libspeex --enable-libtheora --enable-libtwolame --enable-libvidstab --enable-libvorbis --enable-libvpx --enable-libwebp --enable-libx265 --enable-libxml2 --enable-libxvid --enable-libzimg --ena

In [36]:
# Read the binary stream and encode to base64 for direct browser injection
mp4_data = open("compressed_sam-composite-person-bicycle-car-detection.mp4",'rb').read()
data_url = "data:video/mp4;base64," + b64encode(mp4_data).decode()

# Render utilizing IPython display utilities
display(HTML(f"""<video width=800 controls><source src="{data_url}" type="video/mp4"></video>"""))